In [1]:
from io import BytesIO
from hashlib import sha256
from datetime import datetime

In [2]:
def hash256(byte_string):
    return sha256(sha256(byte_string).digest()).digest()

def now():
    return int((datetime.now().timestamp())).to_bytes(4, "big")

In [3]:
class Block:
    def __init__(self, version, prev_hash, merkle_root, timestamp, bits, nonce):
        self.version = version
        self.prev_hash = prev_hash
        self.merkle_root = merkle_root
        self.timestamp = timestamp
        self.bits = bits
        self.nonce = nonce

    # deve leggere la stringa e parse i primi 4 byte la versione, e cosi via
    @classmethod
    def parse(cls, byte_string):
        reader = BytesIO(byte_string)
        version = reader.read(4)
        prev_hash = reader.read(32)
        merkle_root = reader.read(32)
        timestamp = reader.read(4)
        bits = reader.read(4)
        nonce = reader.read(4)
        return cls(version[::-1], prev_hash[::-1], merkle_root[::-1], timestamp[::-1], bits[::-1], nonce[::-1])
    
    def serialize(self):
        return self.version[::-1] + self.prev_hash[::-1] + self.merkle_root[::-1] + self.timestamp[::-1] + self.bits[::-1] + self.nonce[::-1]
    
    def hash(self):
        return hash256(self.serialize())[::-1]
    
    def target(self):
        return int.from_bytes(self.bits[1:], "big") * (256 ** (self.bits[0] - 3))
    
    def is_valid_target(self):
        return int.from_bytes(self.hash(), "big") < self.target()
    
    def update_nonce(self, nonce):
        self.nonce = nonce.to_bytes(4, "big")

    def __str__(self):
        out = dict()
        out["version"] = self.version.hex()
        out["prev_hash"] = self.prev_hash.hex()
        out["merkle_root"] = self.merkle_root.hex()
        out["timestamp"] = self.timestamp.hex()
        out["bits"] = self.bits.hex()
        out["nonce"] = int(self.nonce.hex(), 16)
        return str(out)
    
if __name__ == "__main__":
    header = "0100000000000000000000000000000000000000000000000000000000000000000000003ba3edfd7a7b12b27ac72c3e67768f617fc81bc3888a51323a9fb8aa4b1e5e4a29ab5f49ffff001d1dac2b7c"
    block = Block.parse(bytes.fromhex(header))
    print(block)
    print(block.hash().hex())
    print(hex(block.target()))
    print(block.is_valid_target())

{'version': '00000001', 'prev_hash': '0000000000000000000000000000000000000000000000000000000000000000', 'merkle_root': '4a5e1e4baab89f3a32518a88c31bc87f618f76673e2cc77ab2127b7afdeda33b', 'timestamp': '495fab29', 'bits': '1d00ffff', 'nonce': 2083236893}
000000000019d6689c085ae165831e934ff763ae46a2a6c172b3f1b60a8ce26f
0xffff0000000000000000000000000000000000000000000000000000
True


In [4]:
GENESIS = "0100000000000000000000000000000000000000000000000000000000000000000000003ba3edfd7a7b12b27ac72c3e67768f617fc81bc3888a51323a9fb8aa4b1e5e4a29ab5f49ffff001d1dac2b7c"
blk = Block.parse(bytes.fromhex(GENESIS))
print(blk)
print(blk.hash().hex())
print()
blk.bits = bytes.fromhex("1e02ffff")

height = 0
while True:
    blk.prev_hash = blk.hash()
    blk.timestamp = now()
    height += 1
    tx = "PCD 25/26 block " + str(height)
    blk.merkle_root = hash256(tx.encode('utf-8'))
    i = 0
    blk.update_nonce(i)
    flag = blk.is_valid_target()
    while not flag:
        i += 1
        if i == 2**32:
            i = 0
            blk.timestamp = now()
        blk.update_nonce(i)
        flag = blk.is_valid_target()
        print(blk.hash().hex())
        print(blk)
        print()


{'version': '00000001', 'prev_hash': '0000000000000000000000000000000000000000000000000000000000000000', 'merkle_root': '4a5e1e4baab89f3a32518a88c31bc87f618f76673e2cc77ab2127b7afdeda33b', 'timestamp': '495fab29', 'bits': '1d00ffff', 'nonce': 2083236893}
000000000019d6689c085ae165831e934ff763ae46a2a6c172b3f1b60a8ce26f

be5280e72d8fe3133028eeff37a1688e8fa4cb672e8d0d978eb5b8982e118a13
{'version': '00000001', 'prev_hash': '85c99692046b59a79e20c7ac634c944337ff5909c56b1faad7fa52b5c8405e3f', 'merkle_root': '122bda6dc693f933a7fc9e77d24c64e2c4b73ace94eb1ced58e22e03480910b0', 'timestamp': '69dcc3ae', 'bits': '1e02ffff', 'nonce': 1}

a2e0f96091b813c927d0a1f9fd705977f9f0c338e79a0b45b1c76582da8c9d78
{'version': '00000001', 'prev_hash': '85c99692046b59a79e20c7ac634c944337ff5909c56b1faad7fa52b5c8405e3f', 'merkle_root': '122bda6dc693f933a7fc9e77d24c64e2c4b73ace94eb1ced58e22e03480910b0', 'timestamp': '69dcc3ae', 'bits': '1e02ffff', 'nonce': 2}

df4e1adae9fc5b8cbd9606fd6bb9b3ed641fdbce9693f3ef2e2eac1e51

KeyboardInterrupt: 